In [1]:
# 引入所需的模組
import jieba  # 用於中文分詞
from opencc import OpenCC  # 用於簡繁轉換
from gensim.corpora import WikiCorpus  # 用於處理維基百科文章
from gensim.models import word2vec  # 用於訓練詞向量
import numpy as np  # 用於處理數據和數學運算


In [8]:
# 創建一個 WikiCorpus 對象，並指定維基百科數據的路徑，同時傳入空字典作為字典對象
wiki_corpus = WikiCorpus('zhwiki-20231001-pages-articles-multistream.xml.bz2', dictionary={})

# 初始化文本數量的計數器
text_num = 0

# 打開一個新檔案 'wiki_text.txt' 以便寫入
with open('wiki_text.txt', 'w', encoding='utf-8') as f:
    # 使用迴圈遍歷每一篇維基百科文章
    for text in wiki_corpus.get_texts():
        # 將分詞後的文章以空格連接，並寫入檔案
        f.write(' '.join(text) + '\n')
        # 更新文本數量計數器
        text_num += 1
        # 每處理 10000 篇文章就輸出一次進度
        if text_num % 10000 == 0:
            print('{} articles processed.'.format(text_num))

    # 輸出總共處理的文章數量
    print('{} articles processed.'.format(text_num))

C:\Users\baba1\AppData\Roaming\Python\Python37\site-packages\gensim\utils.py:1333: UserWarning: detected Windows; aliasing chunkize to chunkize_serial
  warnings.warn("detected %s; aliasing chunkize to chunkize_serial" % entity)


10000 articles processed.
20000 articles processed.
30000 articles processed.
40000 articles processed.
50000 articles processed.
60000 articles processed.
70000 articles processed.
80000 articles processed.
90000 articles processed.
100000 articles processed.
110000 articles processed.
120000 articles processed.
130000 articles processed.
140000 articles processed.
150000 articles processed.
160000 articles processed.
170000 articles processed.
180000 articles processed.
190000 articles processed.
200000 articles processed.
210000 articles processed.
220000 articles processed.
230000 articles processed.
240000 articles processed.
250000 articles processed.
260000 articles processed.
270000 articles processed.
280000 articles processed.
290000 articles processed.
300000 articles processed.
310000 articles processed.
320000 articles processed.
330000 articles processed.
340000 articles processed.
350000 articles processed.
360000 articles processed.
370000 articles processed.
380000 art

In [9]:
# 初始化繁簡轉換器
cc = OpenCC('s2t')  # 's2t' 表示簡體轉為繁體

# 開始處理文本
with open('wiki_text_seg.txt', 'w', encoding='utf-8') as new_f:
    with open('wiki_text.txt', 'r', encoding='utf-8') as f:
        for times, data in enumerate(f, 1):
            print('data num:', times)
            # 將文本進行繁簡轉換
            data = cc.convert(data)
            # 使用 jieba 進行分詞
            data = jieba.cut(data)
            # 去除空格
            data = [word for word in data if word != ' ']
            # 用空格連接分詞後的結果
            data = ' '.join(data)

            # 將處理好的文本寫入新文件
            new_f.write(data)


Building prefix dict from the default dictionary ...
Loading model from cache C:\Users\baba1\AppData\Local\Temp\jieba.cache


data num: 1


Loading model cost 0.528 seconds.
Prefix dict has been built successfully.


data num: 2
data num: 3
data num: 4
data num: 5
data num: 6
data num: 7
data num: 8
data num: 9
data num: 10
data num: 11
data num: 12
data num: 13
data num: 14
data num: 15
data num: 16
data num: 17
data num: 18
data num: 19
data num: 20
data num: 21
data num: 22
data num: 23
data num: 24
data num: 25
data num: 26
data num: 27
data num: 28
data num: 29
data num: 30
data num: 31
data num: 32
data num: 33
data num: 34
data num: 35
data num: 36
data num: 37
data num: 38
data num: 39
data num: 40
data num: 41
data num: 42
data num: 43
data num: 44
data num: 45
data num: 46
data num: 47
data num: 48
data num: 49
data num: 50
data num: 51
data num: 52
data num: 53
data num: 54
data num: 55
data num: 56
data num: 57
data num: 58
data num: 59
data num: 60
data num: 61
data num: 62
data num: 63
data num: 64
data num: 65
data num: 66
data num: 67
data num: 68
data num: 69
data num: 70
data num: 71
data num: 72
data num: 73
data num: 74
data num: 75
data num: 76
data num: 77
data num: 78
data nu

In [ ]:
# 設定各種訓練參數
seed = 666  # 設定隨機種子，確保實驗可重現
sg = 0  # 設定使用的訓練算法，0 表示使用 CBOW，1 表示使用 Skip-gram
window_size = 10  # 設定窗口大小，表示在一個句子中，一個詞的上下文範圍內的詞都會被考慮
vector_size = 100  # 設定詞向量的維度
min_count = 1  # 設定最小詞頻，低於這個數字的詞將不會被考慮進訓練
workers = 8  # 設定用於訓練的 CPU 核心數量
epochs = 5  # 設定訓練的輪數
batch_words = 10000  # 設定每一個 batch 包含的最大詞數量

# 讀取分詞後的文本數據
train_data = word2vec.LineSentence('wiki_text_seg.txt')

# 初始化 Word2Vec 模型，並設定相關參數
model = word2vec.Word2Vec(
    train_data,
    min_count=min_count,
    vector_size=vector_size,
    workers=workers,
    epochs=epochs,
    window=window_size,
    sg=sg,
    seed=seed,
    batch_words=batch_words
)

# 儲存訓練好的模型
model.save('word2vec.model')


In [4]:
# 載入之前訓練好的 Word2Vec 模型
model = word2vec.Word2Vec.load('word2vec.model')

# 取得詞向量的維度
print(model.wv['生物'].shape)

# 顯示與 '生物' 最相似的詞彙及相似度
for item in model.wv.most_similar('生物'):
    print(item)


(100,)
('微生物', 0.8050527572631836)
('海洋生物', 0.7481014132499695)
('人類', 0.7411153316497803)
('昆蟲', 0.7315301895141602)
('藻類', 0.7246626615524292)
('醫學園區', 0.6989211440086365)
('生物界', 0.6982381939888)
('動物', 0.697476863861084)
('爬蟲', 0.6949930191040039)
('紅藻', 0.6944056153297424)


In [14]:
# 創建一個形狀為 (model.vector_size,) 的元素全為 0 的 numpy 陣列
padding = np.zeros((model.vector_size,), dtype=np.float32)

# 嘗試取得模型中詞彙 "哥吉拉大怪獸" 的詞向量
try:
    print(model.wv["哥吉拉大怪獸"].shape)
# 若詞彙不存在則觸發例外
except:
    print("OOV")  # OOV 代表 Out of Vocabulary，即詞彙不在詞彙表中
    print(padding.shape)  # 若詞彙不存在，則輸出形狀為 (model.vector_size,) 的全 0 陣列


OOV
(100,)
